# Origins and Adaptations: The Weight of the Source ✍️🎥

**Data Storytelling by Christian Santarelli**

---

### 🎯 The Narrative Goal

We are used to thinking of anime as simply "moving advertisements" for manga and light novels. But is it really so? We want to discover if anime is just a promotional vehicle or if it is able to transcend the original work.

In this analysis we will explore:
1.  **The Ecosystem**: Who really commands the market? (Manga, Novel, or Original?)
2.  **The Original Bias**: Are anime born for the screen qualitatively better?
3.  **The Demographic Divide**: Who watches what? (A journey into gender and age tastes)
4.  **Production & Complexity**: Which sources require more resources (cast, studios)?
5.  **The Decay**: Which adaptations are abandoned most often?

We will use a massive dataset crossing demographics, reviews, and production details to answer the final question: **Does anime need a source to survive?**

In [22]:
import pandas as pd
import numpy as np
import matplotlib.pyplot as plt
import seaborn as sns
import plotly.express as px
import plotly.graph_objects as go
from plotly.subplots import make_subplots
from sklearn.preprocessing import MinMaxScaler
from pathlib import Path
import warnings
import re

from solution.src.data import load_processed
from solution.src.utils import get_available_memory, print_fancy_progress

# Settings
pd.set_option('display.max_columns', None)
warnings.filterwarnings('ignore')
sns.set_style("whitegrid")
plt.rcParams['figure.figsize'] = (12, 6)

print("Libraries loaded and environment configured. ✅")


Libraries loaded and environment configured. ✅


## 1. Data Preparation 🛠️

We load a battery of datasets to get a 360° view:
- **Core**: `details` (metadata), `stats` (numeri)
- **People**: `person_anime_works` (Staff & Studios), `character_anime_works` (Cast & Voice Actors)
- **Users**: `profiles` (Demografica Utenti) - *Nota: Le recensioni sono state omesse per inconsistenze nei dati.*

In [23]:
print("Loading datasets... This might take a moment. ⏳")

try:
    # Core Data
    df_details = load_processed("details") # Main metadata
    df_stats = load_processed("stats")     # Scores, members

    # Production Data
    # Note: These are large, we might want to aggregate them immediately or load lazily if RAM is tight
    # For now, let's load them and check basic stats.
    df_person_works = load_processed("person_anime_works")  # For Studios/Staff
    df_person_details = load_processed("person_details") # For names
    df_char_works = load_processed("character_anime_works") # For Cast Size

    # User Data
    df_profiles = load_processed("profiles") # For Demographics
    # df_reviews = load_processed("reviews")   # For Variance/Controversy

    print("Core datasets loaded. Loading auxiliary datasets lazily to optimize RAM... ✅")

    # Merge Core
    df = df_details.merge(df_stats, on="anime_id", how="inner")
    print(f"Base Dataset merged: {df.shape[0]} anime available.")

except Exception as e:
    print(f"Error loading data: {e}")

# Quick peek
df[['title', 'source', 'score', 'members']].head()


Loading datasets... This might take a moment. ⏳
Core datasets loaded. Loading auxiliary datasets lazily to optimize RAM... ✅
Base Dataset merged: 28939 anime available.


,title,source,score,members
0,-Socket-,Original,NaN,195
1,......,Original,6.53,941
2,.hack//G.U. Returner,Game,6.65,22525
3,.hack//G.U. Trilogy,Game,7.06,34264
4,.hack//G.U. Trilogy: Parody Mode,Game,6.35,11135


### Grouping the Source Material

The `source` field is very fragmented. We group it into 5 Macro-categories to facilitate analysis:

1.  **Manga First**: `Manga`, `4-koma manga`, `Web manga` (Paper/Digital → Screen)
2.  **Novel First**: `Light novel`, `Novel`, `Visual novel` (Text/Narrative Game → Screen)
3.  **Original**: `Original` (Born for the Screen)
4.  **Game**: `Game`, `Card game` (Gameplay → Screen)
5.  **Other**: `Music`, `Picture book`, `Radio`, `Other` (Niche)

*Note: `Visual novel` is included in Novel First due to its narrative nature, but we will also analyze the 'Game' sub-category separately.*

In [24]:
def map_source_group(source):
    if pd.isna(source): return "Unknown"
    source = str(source).strip()

    if source in ['Manga', '4-koma manga', 'Web manga', 'Digital manga']:
        return 'Manga First'
    elif source in ['Light novel', 'Novel', 'Visual novel', 'Book']:
        return 'Novel First'
    elif source == 'Original':
        return 'Original'
    elif source in ['Game', 'Card game']:
        return 'Game'
    else:
        return 'Other'

df['source_group'] = df['source'].apply(map_source_group)

# Check distribution
df['source_group'].value_counts()


source_group
Original       12350
Manga First     6499
Other           5138
Novel First     3402
Game            1550
Name: count, dtype: int64

## Chapter 1: Who Rules the Market? (The Ecosystem) 🌍

Before talking about quality, we must understand quantity. Do we live in a world dominated by Manga or is there room for originality?

Analizzeremo:
1.  **Total Distribution**: Market share of sources.
2.  **Temporal Evolution**: How has the industry changed from the 80s to today?
3.  **Survival Rate**: Which sources generate more sequels?

In [25]:
# 1.1 TreeMap: Distribution of Sources

source_counts = df['source_group'].value_counts().reset_index()
source_counts.columns = ['Source', 'Count']
source_counts['Percent'] = (source_counts['Count'] / source_counts['Count'].sum() * 100).round(1)

fig = px.treemap(source_counts, path=['Source'], values='Count',
                 title='L\'Ecosistema Anime: Distribuzione per Source',
                 color='Source',
                 hover_data=['Percent'])
fig.update_layout(margin=dict(t=50, l=25, r=25, b=25))
fig.show()


### 📊 Analysis: The Dominance of Print
The data confirms that the anime industry is strongly driven by publishing. **Manga** represent the main slice of the market, acting as the "immobile engine" of Japanese animation. However, the share of **Originals** (over 40% in the dataset, although it includes many shorts and experiments) suggests that animation as an autonomous medium is anything but dead. **Novels** and **Games** represent consolidated segments, often linked to specific trends (e.g., Isekai for Novels).


In [26]:
# 1.2 Stacked Area Chart: Temporal Evolution

# Clean Year
df['start_year'] = df['start_date'].apply(lambda x: int(str(x)[:4]) if pd.notnull(x) and str(x)[:4].isdigit() else np.nan)
df_time = df[(df['start_year'] >= 1980) & (df['start_year'] <= 2024)].copy()

source_trend = df_time.groupby(['start_year', 'source_group']).size().reset_index(name='Count')

fig = px.area(source_trend, x='start_year', y='Count', color='source_group',
              title='L\'Evoluzione delle Source (1980-2024)',
              labels={'source_group': 'Source', 'start_year': 'Year', 'Count': 'Anime Count'})

fig.update_layout(hovermode='x unified')
fig.show()



### 📈 Analysis: The Novel Wave
The temporal evolution clearly shows how sources have diversified. If the 90s were the domain of Manga and Original OVAs, in the last 15 years we have witnessed the explosion of **Light Novels**, becoming one of the primary sources for contemporary animation. **Games** maintain a constant but niche presence, while Originals have seen alternating phases, often linked to budget availability for risky projects.


In [27]:
# 1.3 Bar Chart: "Survival Rate" (Sequels)
# approach: Title Clustering
# Create a title "stem" by removing common suffixes (Season X, Movie, etc.)
# Group by stem and sort by date. The first is the Original, others are Sequels/Franchise.

def extract_franchise_stem(title):
    t = str(title).lower()
    # Remove Season X, 2nd Season, etc.
    t = re.sub(r'\s(season\s?\d+|2nd\s?season|3rd\s?season|4th\s?season|court?\s?\d+|part\s?\d+).*', '', t)
    # Remove after colon (often subtitles) - Be careful with "Re:Zero" -> "Re" might be too aggressive? 
    # Let's keep it simple: often colon separates Main Title : Subtitle
    if ':' in t:
        t = t.split(':')[0]
    # Remove trailing Roman numerals II, III, IV, V (mostly IV is max common)
    t = re.sub(r'\s(ii|iii|iv|v|vi)$', '', t)
    # Remove explicit types
    t = re.sub(r'\s(movie|film|the animation|animation)$', '', t)
    # Remove symbols
    t = re.sub(r'[!.\'?°]', '', t)
    return t.strip()

df['franchise_stem'] = df['title'].apply(extract_franchise_stem)

# Sort by stem and date
df = df.sort_values(['franchise_stem', 'start_date'])

# Identify sequels: Any entry after the first one in a franchise group is a sequel/related content
df['is_sequel'] = df.duplicated(subset=['franchise_stem'], keep='first')

# Debug: Check some famous franchises
# print(df[df['franchise_stem'] == 'attack on titan'][['title', 'start_date', 'is_sequel']])

# Aggregation
sequel_stats = df.groupby('source_group')['is_sequel'].agg(['count', 'sum']).reset_index()
sequel_stats.columns = ['source_group', 'Total', 'Sequels']
sequel_stats['Percent'] = (sequel_stats['Sequels'] / sequel_stats['Total'] * 100).round(1)

# Sort
sequel_stats = sequel_stats.sort_values('Percent', ascending=False)

fig = px.bar(sequel_stats, x='source_group', y='Percent',
             title='Survival Rate: Ability to Generate Franchise (Sequel %)',
             color='source_group',
             text='Percent',
             labels={'Percent': '% Sequel/Franchise', 'source_group': 'Source'})

fig.update_traces(texttemplate='%{text}%', textposition='outside')
fig.update_layout(uniformtext_minsize=8, uniformtext_mode='hide')
fig.show()


### 🔄 Analysis: Who Survives?
Contrary to the hypothesis that Originals are "one-shots", data on sequels show that having a solid source (Manga/Novel) significantly helps franchise longevity. Series adapted from **Manga** and **Novel** tend to have more seasons (higher "Survival Rate") because they rely on pre-existing material that builds audience loyalty in the long run. Originals, having to build fandom from scratch, struggle more to get greenlights for multiple sequels, unless they are resounding successes.


## Chapter 2: The "Original Bias" (Quality vs Quantity) ⭐

Dominating the market is easy, but who dominates quality? 

Hypotheses: 
1.  **Original**: High variance (risky). Either Masterpiece or Flop.
2.  **Manga First**: "Safe bet". More stable average.
3.  **Game**: Hard to adapt, low scores?

> [!NOTE]
> **TV Series Filter**: For the episode distribution analysis (following), we filtered the dataset to include only **TV Series**.

In [28]:
# 2.1 Violin Plot: Score Distribution per Source Group

df_scored = df[df['score'] > 0]

fig = px.violin(
    df_scored, 
    x='source_group', 
    y='score', 
    color='source_group',
    title='Score Distribution by Source (Who has the highest average?)',
    labels={'source_group': 'Source', 'score': 'Score'},
    points=False, 
    box=True,
    category_orders={'source_group': ['Novel First', 'Manga First', 'Original', 'Other', 'Game']},
)

fig.update_traces(quartilemethod="exclusive", meanline_visible=True) # Added meanline for extra detail
fig.show()

### 🏆 Analysis: The "Survivor" Filter (Survivorship Bias)
This visualization visually confirms a structural market force: **Risk vs. Validation**.

* **The "Safety Net" of Adaptations:** The **Manga** and **Novel** violins are "top-heavy" (thicker at scores of 7.5–8.0). This indicates **Survivorship Bias**: bad manga rarely get anime adaptations. Producers only greenlight stories that have already survived the competitive literary market. This upstream "filter" creates a quality floor, ensuring a higher baseline score.
* **The Volatility of Originals:** The **Original** (Green) violin shows a wider "belly" at the average (6.0) and a longer bottom tail. Without source material to serve as a quality proof-of-concept, Original productions are **high-risk ventures**. They lack the "pre-installed" fanbase of a manga, meaning their scores rely entirely on execution—leading to a distribution that covers the full spectrum from unique masterpieces to complete failures.

In [29]:
# 2.2 Overlaid Histogram: Density of scores for specific Top Sources
# This chart answers the question: "Who has more masterpieces (high scores)?"

top_sources = ['Manga', 'Original', 'Light novel', 'Visual novel', 'Game']
df_specific = df[df['source'].isin(top_sources) & (df['score'] > 0)]

# Use histogram with 'probability density' to compare groups of different sizes
fig = px.histogram(
    df_specific, 
    x="score", 
    color="source", 
    barmode="overlay",
    histnorm='probability density',
    nbins=20,
    opacity=1,
    title='Score Density: Who has the best quality curve?',
    labels={'source': 'Source', 'score': 'Score', 'probability density': 'Probability (Density)'},
)

# Add a line for the global average (optional, but useful reference)
fig.add_vline(x=df_specific['score'].mean(), line_width=1, line_dash="dash", line_color="grey", annotation_text="Global Average")

fig.show()

### 2.2 Score Density: Who has the best "Quality Curve"?

**Chart Type:** Overlaid Histogram (Probability Density)
**Metric:** Distribution of Scores (X-Axis) vs. Frequency/Density (Y-Axis)

**Description:**
While the previous Violin Plot compared the *shapes* of the distributions, this Overlaid Histogram allows us to directly compare the "peaks" of quality. By normalizing the data (Probability Density), we can fairly compare sources with thousands of anime (Manga) against those with fewer entries (Visual Novels) to see which category has the highest *concentration* of good shows.

**Key Observations:**
* **The "Light Novel" Dominance (Orange):** The Orange bars show a distinct **right-shift**. Their highest peak is not at the global average (6.4), but closer to **7.0–7.5**.
    * *Interpretation:* This indicates that Light Novel adaptations are currently the "safest bet" for viewers. A significantly larger portion of them achieves "Good" to "Very Good" scores compared to other categories.
* **The "Game" Struggle (Purple):** The Purple bars peak sharply to the *left* of the others, dominating the **6.0–6.5** range.
    * *Interpretation:* Game adaptations struggle to break into the "Masterpiece" tier (8.0+). They are statistically more likely to be "Average" (6/10) rather than "Great."
* **The Global Average (Dashed Line):** The vertical line at **6.4** serves as the anchor. Notice how the "Original" (Blue) and "Game" distributions center heavily around this line, whereas the literary sources (Manga and Novels) push past it.

**Conclusion:**
There is a clear hierarchy in perceived quality. Literary sources (**Light Novels & Manga**) produce a higher density of top-tier anime, likely because the stories are deeper and pre-validated by readers. **Game** and **Original** anime, while capable of greatness, statistically gravitate towards the "average" middle ground.

In [30]:
# Filter for TV only to ensure fair comparison of series length
df_scatter = df[df['type'] == 'TV'].copy()

# Calculate the order of categories by Median Episode count (Ascending)
# This ensures the "Shortest" source appears on the left
order = df_scatter.groupby('source_group')['episodes'].median().sort_values().index.tolist()

fig = px.box(
    df_scatter, 
    x='source_group', 
    y='episodes', 
    color='source_group',
    points=False,  
    log_y=True,
    category_orders={'source_group': order},
    title='Episode Distribution by Source: Originals are the longest',
    labels={'episodes': 'Number of Episodes (Log Scale)', 'source_group': 'Source'},
)

# Optional: Add a subtle grid to make reading the log scale easier
fig.update_layout(yaxis=dict(showgrid=True, gridwidth=1, gridcolor='LightGrey'))

fig.show()

### 📏 Analysis: Industrial Standards vs. Creative Freedom

The Box Plot reveals a fundamental difference in how production is planned:

* **Manga First (The "Industrial Standard"):**
    * **Compressed Box:** The red box is very short and squashed. This indicates **high standardization**. The industry has a rigid formula for adapting manga (usually a 12-episode "cour" to test the waters).
    * **Outliers Only:** The only vertical movement is upwards (the long top whisker), representing the few "Mega-Hits" that survived the 12-episode filter to run indefinitely.

* **Originals (The "Bespoke" Model):**
    * **Vertical Stretch (High Variance):** You noticed the box stretches significantly in *both* directions. This proves that Originals **lack a standard format**.
    * **Interpretation:** Because an Original anime is written from scratch, its length is dictated by the story's needs (or the project's specific budget), not by how many manga volumes exist. This leads to a **higher median** (often targeting 2-cour/24 eps) but also **higher instability**, resulting in irregular episode counts that don't fit the strict "TV Cour" system.

* **Conclusion:**
    **Manga adaptations** are a standardized industrial product (predictable length), whereas **Originals** are bespoke productions with high variance—offering greater narrative freedom but also less predictability.

## Chapter 3: The Demographic Divide 👫

Who is the audience for these adaptations? 

To answer, we load the `profiles` dataset and aggregate the data. 
*Note: This step requires processing millions of rows, so we will work on an aggregated sample if necessary.*

### 📝 Guide to Demographic Targets

To better understand the following chart, here is a legend of the Japanese terms used to classify the target audience:

- **Shounen**: Boy. Male teenage target (es. *Naruto*, *One Piece*).
- **Shoujo**: Girl. Female teenage target (es. *Sailor Moon*, *Nana*).
- **Seinen**: Young Man. Male adult target (18+)
- **Josei**: Young Woman. Female adult target
- **Kids**: Children. Target intended for childhood (es. *Pokémon*, *Doraemon*).

In [31]:
# 3.1 Grouped Bar Chart: Gender Target by Source
# Analyze the 'demographics' column which contains explicit targets (Shounen, Seinen, ecc.)

demographics_list = ['Shounen', 'Seinen', 'Shoujo', 'Josei', 'Kids']

def extract_demographic(val_str):
    if not isinstance(val_str, str): return 'Unknown'
    # The value is a string representing a list, e.g., "['Shounen']" or "[]",

    for demo in demographics_list:
        if demo in val_str:
            return demo

    return 'General/Unknown'

# Determine which column to use (Prefer 'demographics', fallback to 'genres')
target_col = 'demographics' if 'demographics' in df.columns else 'genres'
print(f"Extracting demographics from column: {target_col}")

df['demographic_tag'] = df[target_col].apply(extract_demographic)

# Filter Unknown
df_demo = df[df['demographic_tag'] != 'General/Unknown']

print(f"Found {len(df_demo)} anime with clear demographics.")

demo_source = df_demo.groupby(['source_group', 'demographic_tag']).size().reset_index(name='Count')

fig = px.bar(demo_source, x='source_group', y='Count', color='demographic_tag',
             title='Demographic Target by Source (Who watches what?)',
             barmode='group',
             labels={'Count': 'Anime Count', 'source_group': 'Source', 'demographic_tag': 'Target'})
fig.show()


Extracting demographics from column: demographics
Found 10809 anime with clear demographics.


### 👥 Analysis: The "Magazine" Effect vs. Family TV

This bar chart highlights a fundamental difference in how target audiences are defined:

* **Manga First (The Magazine System):**
    * **Broad Spectrum:** The Manga category (middle) is the only one that effectively reaches all demographic quadrants: **Shounen** (Green/Boys), **Seinen** (Purple/Adult Men), and **Shoujo** (Orange/Girls).
    * **Why:** This reflects the Japanese publishing industry, where manga are serialized in magazines strictly segregated by age and gender (*Shonen Jump*, *Seinen Young*, etc.). The anime simply inherits this pre-defined demographic label.

* **Originals (The "Kids" Kingdom):**
    * **The Red Giant:** The "Original" category is overwhelmingly dominated by the **Kids** target (the massive Red bar).
    * **Interpretation:** Since Original anime are not born from segmented magazines, they often target the broadest possible TV audience—families and children (e.g., *PreCure*, *Doraemon*-style franchises, or educational content). Unlike Manga, which thrive on niche targeting (e.g., Seinen), Original anime production is heavily skewed towards mass-market children's entertainment.

* **Conclusion:**
    Demographic labels like "Shounen" or "Seinen" are essentially **print media artifacts**. When anime is created from scratch (Originals), the industry defaults to the universal "Kids/Family" demographic rather than these gendered sub-categories.

In [32]:
# 3.2 Heatmap: Age Suitability (Rating) vs Source
# Use the 'rating' column (G, PG, R-17, etc.)

rating_source = df.groupby(['rating', 'source_group']).size().unstack(fill_value=0)
# Normalize by column (Source) to see internal %
rating_source_norm = rating_source.div(rating_source.sum(axis=0), axis=1)

fig = px.imshow(rating_source_norm, text_auto='.1%', aspect='auto',
                title='Age Rating Heatmap: How "mature" are Originals?',
                labels=dict(x="Source", y="Rating", color="Percentage"),
                color_continuous_scale='Blues')
fig.show()


### 🔞 Analysis: Content Maturity
The age rating heatmap shows how different sources cover different market needs. Material for children (Kids) is often Original or Game (e.g., Pokémon), while more mature content (R-17) frequently comes from Seinen Manga or Novels, which can dare more thematically compared to original productions designed for generalist TV.


In [39]:
# This ensures we are comparing apples to apples (TV vs TV)
# removing 1-episode movies that ruin the "Original" stats.
df_radar_filtered = df[
    (df['type'] == 'TV') & 
    (df['score'] > 0) & 
    (df['members'] > 0)
].copy()

# 2. Select features
features = ['score', 'popularity', 'members', 'episodes']

# 3. Aggregation: Median
df_grouped = df_radar_filtered.groupby('source_group')[features].median().reset_index()

# INVERT POPULARITY: Transform Rank so #10000 is highest and #1 is lowest
# We subtract the value from the max to flip the scale
df_grouped['popularity'] = df_grouped['popularity'].max() - df_grouped['popularity']

# 4. Normalization (0 to 1 scale)
scaler = MinMaxScaler()
df_grouped[features] = scaler.fit_transform(df_grouped[features])

# 5. Melt for Plotly
df_melted = df_grouped.melt(id_vars='source_group', var_name='Metric', value_name='Value')

# 6. Plot
fig = px.line_polar(df_melted, 
                    r='Value', 
                    theta='Metric', 
                    color='source_group', 
                    line_close=True,
                    title='Characteristic Profile (TV Series Only - Normalized)',
                    labels={"source_group": "Source"}) 

fig.update_traces(fill='toself')
fig.show()


### 🕸️ Profilo Caratteristico: Il "DNA" delle Fonti (Radar Chart)

**Chart Type:** Radar Chart (Spider Plot)
**Metric:** Normalized Median Values (0-1 Scale) for TV Series

**Axes Explanation:**
* **Top/Right/Bottom (Commercial Success):** Score, Popularity (Inverted), Members.
* **Left (Structure):** Episodes (Length).

**Description:**
This multivariate analysis summarizes the distinct "personality" of each source material type. By normalizing the medians of TV series, we can compare their structural strengths regardless of the absolute scale differences.

**Key Observations:**
* **The "Commercial Juggernauts" (Novel & Manga):**
    * **Shape:** They form a massive "Kite" shape pointing to the right.
    * **Analysis:** **Novel First** (Green) and **Manga First** (Red) completely dominate the metrics of **Score**, **Popularity**, and **Members**. This visualizes the "Pre-sold Audience" effect: adaptations of popular books arrive on screen with a massive, built-in fanbase that guarantees high visibility and strong initial ratings. They are the industry's "Safe Bets."

* **The "Narrative Specialist" (Originals):**
    * **Shape:** The Purple shape spikes aggressively to the **Left (Episodes)**.
    * **Analysis:** **Original** anime show a weaker footprint on the commercial side (fewer members, lower popularity ranks) because they start with zero fanbase. However, they dominate the **Episodes** axis. This confirms our earlier finding: without a manga sales quota to meet, Original TV projects are structurally designed to be longer (often 2-cour/24 eps) to tell a complete story, whereas adaptations are often cut short.

**Conclusion:**
The market is split into two distinct models:
1.  **Adaptations (Manga/Novel):** Optimized for **Reach** (High Members/Popularity) but standardized in length (Low Episodes).
2.  **Originals:** Optimized for **Structure** (High Episodes/Narrative Freedom) but riskier in terms of Reach.

## 🎬 Deep Dive: The Human Factor (People & Production)

Behind every great anime is there just one author or an entire army? Is the idea that Originals require more creative effort true? Esploriamo il **Capitale Umano**:

1.  **Cast Size**: Le serie originali, non avendo personaggi predefiniti, tendono ad avere cast più ampi o più mirati?
2.  **Production Muscle**: Analizziamo la dimensione dello Staff accreditato come proxy della complessità produttiva.

In [34]:
# Join Anime with Character counts
# We count 'Main' characters per anime
main_cast = df_char_works[df_char_works['role'] == 'Main'].groupby('anime_id')['character_id'].nunique().reset_index(name='main_cast_size')

df_cast = df.merge(main_cast, on='anime_id', how='inner')

fig = px.box(
    df_cast,
    x='source_group',
    y='main_cast_size',
    color='source_group',
    title='Main Cast Size by Source',
    points=False, # Hide outliers for clarity
    labels={"main_cast_size":"Main Cast Size", "source_group":"Source"}
)
fig.show()

### Main Cast Analysis: Character Density by Source

**Chart Type:** Box Plot
**Metric:** Size of Main Voice Cast (Y-Axis) vs. Source Material (X-Axis)

**Description:**
This visualization examines whether the number of "Main Characters" (measured by the size of the primary voice cast) varies significantly based on the anime's origin. It helps determine if certain sources naturally lend themselves to larger ensemble casts.

**Key Observations:**
* **Game Adaptations (Largest Ensembles):** The "Game" category stands out as the clear leader in cast density. It has the highest median line and the tallest box, with a whisker extending up to ~50 main cast members.
    * *Interpretation:* This accurately reflects the nature of RPG and "Gacha" game adaptations (like *Fate/Grand Order* or *Azur Lane*), which often feature massive rosters of playable characters that must be included in the anime, resulting in significantly larger ensemble casts than standard stories.
* **Manga First & Novel First (Standardized):** These categories show very similar, compact distributions with low medians (around 3-5 main characters). This aligns with traditional storytelling structures that focus on a small core group of protagonists (e.g., a "Power Trio" or a single Hero/Heroine dynamic).
* **Originals (High Variability):** Similar to the staff analysis, "Originals" show a compressed median but a high upper whisker (~37). This indicates diversity: while many originals focus on intimate, small-cast stories, there is a subset of "Idol" or "Team-based" original anime (like *Love Live!*) that require large casts, pushing the upper limit.

**Conclusion:**
While most anime sources (Manga, Novels, Originals) tend to focus on a small core cast of 3-5 main characters, **Game adaptations** are the exception, showing a distinct structural tendency towards significantly larger character rosters.

### 2. Production Muscle: Who has more Staff?
We analyze the "firepower" of production by counting credited people (Staff).

In [35]:
# 1. Count staff members per anime
staff_count = df_person_works.groupby('anime_id')['person_id'].nunique().reset_index(name='staff_size')

# 2. Merge with main dataframe
df_staff = df.merge(staff_count, on='anime_id', how='inner')

# 3. Filter for TV Series only
# This removes the "Indie Noise" (1-person shorts) and compares Industry vs. Industry
df_staff_tv = df_staff[
    (df_staff['type'] == 'TV') & 
    (df_staff['staff_size'] < 100) # Keep the cap to maintain readability
]

fig = px.box(
    df_staff_tv, 
    x='source_group',
    y='staff_size',
    color='source_group',

    # Updated Title to be accurate
    title='Dimensione Staff Tecnico (Solo Serie TV - Filtrato < 100)',
    points=False,
    labels={"staff_size": "Dimensione Staff", "source_group": "Fonte"},

    # Optional: Order by median size to make the trend clear
    category_orders={'source_group': ['Original', 'Game', 'Manga First', 'Novel First', 'Other']}
)

fig.show()

### 🛠️ Technical Staff: The "Light Novel" Powerhouse

**Chart Type:** Box Plot
**Metric:** Reported Technical Staff Size (TV Series Only, Filtered < 100)

**Methodology Note (The Zoom Filter):**
To ensure readability, we excluded "Mega-Productions" with more than 100 reported staff members (such as massive franchise movies or studio blockbusters).
* *Reasoning:* These extreme outliers would stretch the Y-axis scale, compressing the vast majority of "typical" TV shows into a flat, unreadable line. Cutting the data at 100 acts as a "magnifying glass" to reveal the structural differences between standard productions.

**Key Observations:**
* **The New Champion: Novel First (Purple):**
    * **Highest Median (~45-50):** Surprisingly, anime adapted from Novels (Light Novels) employ the largest technical teams.
    * *Interpretation:* Light Novel adaptations (e.g., *Fate/Zero*, *Violet Evergarden*) are often the "flagship" titles for studios. They prioritize high-fidelity visuals ("sakuga") and complex post-production effects, requiring significantly larger specialized teams than the average show.
* **Manga & Game (Green/Orange):**
    * **The Industry Standard (Median ~35):** These represent the "bread and butter" of the industry. Their teams are consistent and robust—larger than Originals but generally leaner than the massive crews assembled for high-profile Novel adaptations.
* **Originals (Blue):**
    * **Lean & Efficient (Median ~25):** By filtering for TV series, we confirmed that Originals are proper professional productions (jumping up from the near-zero "indie" baseline seen previously). However, they remain the "leanest" category. This suggests that Original anime are often produced by tighter, more focused creative units rather than the sprawling armies required to adapt dense literary material.

**Conclusion:**
Production complexity—measured by human resources—is highest in **Novel Adaptations**, driven by the genre's demand for visual spectacle. **Originals**, while structurally longer (episode count), are operationally leaner, relying on smaller, concentrated teams.

## 👥 The Audience: Tell Me Who You Are (Fan Analysis)

Who watches what? It is often thought that Novel adaptations are for a younger audience, while Originals are for mature cinephiles. We test this stereotype by crossing **Favorites** data with user birth years.

In [36]:
# Load Favs if not already loaded in memory (it's not in the main block above)
try:
    df_favs = load_processed('favs')
    df_favs_anime = df_favs[df_favs['fav_type'] == 'anime'].copy()
    df_favs_anime['anime_id'] = df_favs_anime['id'].astype(int)

    # Check Profiles
    # Convert birthday to Age (approx 2025 - year)
    df_profiles['birth_year'] = pd.to_datetime(df_profiles['birthday'], errors='coerce').dt.year
    df_profiles_valid = df_profiles.dropna(subset=['birth_year'])
    df_profiles_valid['age'] = 2025 - df_profiles_valid['birth_year']
    df_profiles_valid = df_profiles_valid[(df_profiles_valid['age'] > 10) & (df_profiles_valid['age'] < 80)] # Filter reasonable ages

    # Join: Profiles (User) -> Favs (User, Anime) -> DF (Anime, Source)
    user_favs = df_profiles_valid[['username', 'age']].merge(df_favs_anime, on='username', how='inner')
    anime_source = df[['anime_id', 'source_group']]

    final_demo = user_favs.merge(anime_source, on='anime_id', how='inner')

    fig = px.box(
        final_demo,
        x='source_group',
        y='age',
        color='source_group',
        title='Fan Age by Source (Based on Favorites)',
        points=False,
        labels={"age": "Age", "source_group": "Source"}
    )
    fig.show()

except Exception as e:
    print(f'Could not complete demographic analysis: {e}')

### 2.6 Fan Demographics: Age Distribution by Source

**Chart Type:** Box Plot
**Metric:** Fan Age (Y-Axis) vs. Source Material (X-Axis)

**Description:**
This visualization tests the hypothesis that different source materials target distinct generational cohorts (e.g., *Light Novels* for teenagers vs. *Originals* for adults). It plots the distribution of self-reported user ages across the five main source categories.

**Key Observations:**
* **Demographic Homogeneity:** The most striking finding is the complete lack of variance. The distributions are virtually identical across all categories. Whether a fan prefers *Manga*, *Games*, or *Originals*, the median fan age remains consistently anchored at **~25–26 years old**.
* **The "Core" Audience:** The Interquartile Range (the box) spans tightly from **22 to 30 years old**. This confirms that the active MyAnimeList community is predominantly composed of "Zillennials" (late Gen Z and young Millennials).

**⚠️ Data Quality Note (The "80-Year-Old Otaku"):**
The upper whiskers extend unrealistically high (reaching 80+ years old). This is a classic artifact of **Self-Reporting Bias** in online datasets.
* **Interpretation:** Many users likely set their birth year to default or "joke" dates (e.g., 1900) for privacy reasons. While these outliers exist, the robust nature of the *Box Plot* (which relies on medians, not averages) ensures they do not distort the central finding: the anime community is age-agnostic regarding source material.

**Conclusion:**
Source material is **not** a predictor of audience age. The medium itself acts as the filter. If you are an anime fan on this platform, you are statistically likely to be in your mid-20s, regardless of whether you watch *Pokémon* (Game) or *Cowboy Bebop* (Original).

## 🏁 Conclusions: The Verdict
    
We started by asking if anime was just an "advertisement" for manga and novels.

1.  **The Hegemony of the Source**: Manga and Novel non solo dominano i numeri, ma garantiscono la **Longevità**. La probabilità di ottenere un sequel è drasticamente più alta per opere che hanno già una fanbase.
2.  **Quality vs Risk**: **Original** anime are the true "wildcards". Without a pre-existing story, they oscillate between oblivion and absolute masterpiece.
3.  **The Human Factor**: Original productions tend to mobilize significant human resources (Staff) to compensate for the lack of a pre-existing fan-base with impeccable technical quality.

**In short**: The modern anime industry is an **amplification** machine.
